# Baseline Recommender 1

Full feature space: 
use all 518 audio features, scale them, then calculate nearest neighbours/cosine similarity
no PCA

In [1]:
import pandas as pd
import numpy as np

from sklearn.preprocessing import StandardScaler
from sklearn.neighbors import NearestNeighbors

In [2]:
tracks = pd.read_csv(
    "../data/raw/fma_metadata/tracks.csv",
    index_col=0,
    header=[0, 1]
)

features = pd.read_csv(
    "../data/raw/fma_metadata/features.csv",
    index_col=0,
    header=[0, 1, 2]
)

In [3]:
small_tracks = tracks[
    tracks[("set", "subset")] == "small"
].copy()

small_features = features.loc[small_tracks.index].copy()

In [4]:
small_tracks.shape


(8000, 52)

In [5]:
small_features.shape

(8000, 518)

In [6]:
small_features.isna().sum().sum()

np.int64(0)

In [7]:
small_features.dtypes.value_counts()

float64    518
Name: count, dtype: int64

In [8]:
# scale the features

scaler = StandardScaler()

X_scaled = scaler.fit_transform(small_features)

In [9]:
X_scaled.shape

(8000, 518)

In [10]:
X_scaled.mean()


np.float64(-1.0608931150985685e-16)

In [11]:
X_scaled.std()

np.float64(1.0)

In [12]:
# fit the nearest neighbour model

nn_model = NearestNeighbors(
    n_neighbors=11,
    metric="cosine",
    algorithm="brute"
)

nn_model.fit(X_scaled)

,"n_neighbors n_neighbors: int, default=5Number of neighbors to use by default for :meth:`kneighbors` queries.",11
,"algorithm algorithm: {'auto', 'ball_tree', 'kd_tree', 'brute'}, default='auto'Algorithm used to compute the nearest neighbors:- 'ball_tree' will use :class:`BallTree`- 'kd_tree' will use :class:`KDTree`- 'brute' will use a brute-force search.- 'auto' will attempt to decide the most appropriate algorithm based on the values passed to :meth:`fit` method.Note: fitting on sparse input will override the setting ofthis parameter, using brute force.",'brute'
,"metric metric: str or callable, default='minkowski'Metric to use for distance computation. Default is ""minkowski"", whichresults in the standard Euclidean distance when p = 2. See thedocumentation of `scipy.spatial.distance<https://docs.scipy.org/doc/scipy/reference/spatial.distance.html>`_ andthe metrics listed in:class:`~sklearn.metrics.pairwise.distance_metrics` for valid metricvalues.If metric is ""precomputed"", X is assumed to be a distance matrix andmust be square during fit. X may be a :term:`sparse graph`, in whichcase only ""nonzero"" elements may be considered neighbors.If metric is a callable function, it takes two arrays representing 1Dvectors as inputs and must return one value indicating the distancebetween those vectors. This works for Scipy's metrics, but is lessefficient than passing the metric name as a string.",'cosine'
,"radius radius: float, default=1.0Range of parameter space to use by default for :meth:`radius_neighbors`queries.",1.0
,"leaf_size leaf_size: int, default=30Leaf size passed to BallTree or KDTree. This can affect thespeed of the construction and query, as well as the memoryrequired to store the tree. The optimal value depends on thenature of the problem.",30
,"p p: float (positive), default=2Parameter for the Minkowski metric fromsklearn.metrics.pairwise.pairwise_distances. When p = 1, this isequivalent to using manhattan_distance (l1), and euclidean_distance(l2) for p = 2. For arbitrary p, minkowski_distance (l_p) is used.",2
,"metric_params metric_params: dict, default=NoneAdditional keyword arguments for the metric function.",None
,"n_jobs n_jobs: int, default=NoneThe number of parallel jobs to run for neighbors search.``None`` means 1 unless in a :obj:`joblib.parallel_backend` context.``-1`` means using all processors. See :term:`Glossary <n_jobs>`for more details.",None
Name,Type,Value
effective_metric_ effective_metric_: strMetric used to compute distances to neighbors.,str,'cosine'
effective_metric_params_ effective_metric_params_: dictParameters for the metric used to compute distances to neighbors.,dict,{}


In [13]:
# create a recommendation function

def recommend_similar_tracks(track_id, n=10):

    if track_id not in small_tracks.index:
        raise ValueError("Track ID not found in FMA Small.")

    position = small_tracks.index.get_loc(track_id)

    seed_artist = small_tracks.loc[
        track_id, ("artist", "id")
    ]

    # Retrieve more candidates than needed because
    # some will be removed by the artist filter
    candidate_count = min(n + 50, len(small_tracks))

    distances, indices = nn_model.kneighbors(
        X_scaled[position].reshape(1, -1),
        n_neighbors=candidate_count
    )

    rows = []

    for idx, distance in zip(indices[0], distances[0]):

        candidate_id = small_tracks.index[idx]

        # exclude seed track itself
        if candidate_id == track_id:
            continue

        candidate_artist = small_tracks.loc[
            candidate_id, ("artist", "name")
        ]

        # exclude same artist
        if candidate_artist == seed_artist:
            continue

        rows.append({
            "track_id": candidate_id,
            "artist": candidate_artist,
            "title": small_tracks.loc[
                candidate_id, ("track", "title")
            ],
            "genre": small_tracks.loc[
                candidate_id, ("track", "genre_top")
            ],
            "cosine_distance": distance,
            "similarity": 1 - distance
        })

        if len(rows) == n:
            break

    results = pd.DataFrame(rows).set_index("track_id")

    return results

In [14]:
# try a track

small_tracks[
    [
        ("artist", "name"),
        ("track", "title"),
        ("track", "genre_top"),
    ]
].sample(20)

artist  \
                                        name   
track_id                                       
12062                              Big Blood   
21677                     Guidance Counselor   
113032                              One S.P.   
91621                              Rolemusic   
126675                             Sleep Out   
134933        Turku, Nomads of the Silk Road   
54624                               Starseed   
133434                             TRG Banks   
85318                               Titus 12   
130952                       Albin Andersson   
85290                                Koalips   
101118                  La Sabrosa Sabrosura   
16340                                Twizzle   
127402    chicago_word_brigade & brass-lines   
17735                                Liturgy   
23353                                   Choc   
40229                              Big Blood   
121321                       Coin Locker Kid   
144475                            Nick Jaina   
106563                         Apache Tomcat   

                                      track                 
                                      title      genre_top  
track_id                                                    
12062                         Sleepin' Time           Folk  
21677                   I Don't Wanna Speak            Pop  
113032     I Told Jesus ft. Sharam Shahbazi        Hip-Hop  
91621         Another beek beep beer please     Electronic  
126675                        You Look Pale           Rock  
134933                              -Misket  International  
54624                       Grapes of Wrath           Rock  
133434                        Keith in 1987   Instrumental  
85318                   Rougher Than Riddim     Electronic  
130952         You Never Took Me For A Walk           Folk  
85290                        Her Cold Touch     Electronic  
101118                  El Sonidero de Amor  International  
16340            Barefoot Girl/ Pebble Road            Pop  
127402                             C8H11NO2   Experimental  
17735                         Ecstatic Rite           Rock  
23353     Eigenvalue Subspace Decomposition     Electronic  
40229                   The Sound & The Sea           Folk  
121321                            annabelle        Hip-Hop  
144475      The Dinner Party (Instrumental)           Folk  
106563             Nothing On But The Radio           Rock

In [15]:
recommend_similar_tracks(140, n=5)

,artist,title,genre,cosine_distance,similarity
track_id,,,,,
44805,Monk Turner + Fascinoma,Start Again,Pop,0.450473,0.549527
6803,Watcha Clan,Balkan Qoulou,International,0.480359,0.519641
77564,Bryyn,Abba Ingee,Pop,0.482405,0.517595
110451,Papascandy,Linton,International,0.493989,0.506011
52953,Marissa Nadler,Your Heart Is A Twisted Vine,Folk,0.507851,0.492149


In [16]:
# basic evaluation metric
# Of its 10 nearest neighbours, what proportion have the same genre_top

def genre_agreement_at_k_exclude_artist(
    X,
    tracks_df,
    k=10,
    candidate_pool=100
):
    model = NearestNeighbors(
        metric="cosine",
        algorithm="brute"
    )

    model.fit(X)

    # Retrieve extra neighbours because some will be
    # removed when they belong to the same artist.
    n_candidates = min(candidate_pool + 1, len(tracks_df))

    _, indices = model.kneighbors(
        X,
        n_neighbors=n_candidates
    )

    genres = tracks_df[("track", "genre_top")].to_numpy()
    artists = tracks_df[("artist", "name")].to_numpy()

    scores = []

    for i in range(len(tracks_df)):

        # Skip seeds without a genre label
        if pd.isna(genres[i]):
            continue

        valid_neighbours = []

        for neighbour_idx in indices[i]:

            # Exclude the seed itself
            if neighbour_idx == i:
                continue

            # Exclude tracks by the same artist
            if artists[neighbour_idx] == artists[i]:
                continue

            valid_neighbours.append(neighbour_idx)

            if len(valid_neighbours) == k:
                break

        if len(valid_neighbours) == 0:
            continue

        neighbour_genres = genres[valid_neighbours]

        # Ignore neighbours with missing genre labels
        valid_genres = ~pd.isna(neighbour_genres)

        if valid_genres.sum() == 0:
            continue

        agreement = (
            neighbour_genres[valid_genres] == genres[i]
        ).mean()

        scores.append(agreement)

    return np.mean(scores)

In [17]:
baseline1_genre_agreement = (
    genre_agreement_at_k_exclude_artist(
        X_scaled,
        small_tracks,
        k=10
    )
)

baseline1_genre_agreement

np.float64(0.34342500000000004)

In [18]:
import time

start = time.time()

_ = nn_model.kneighbors(X_scaled[:100])

elapsed = time.time() - start

print(f"100 queries took {elapsed:.4f} seconds")

100 queries took 0.0180 seconds


## Baseline 1 — Full audio feature space

- Dataset: FMA Small
- Tracks: 8,000
- Audio features: 518
- Scaling: StandardScaler
- Similarity metric: Cosine distance
- Model: NearestNeighbors
- Genre agreement@10: 0.3434
- Query time: 0.0282 seconds for 100 queries

The full audio feature space produces neighbourhoods substantially
more coherent than random genre assignment (0.125 baseline).
Recommendations can cross top-level genres, suggesting that the
audio features capture relationships not represented by coarse genre labels.

The standardized feature matrix has mean ≈ 0 and standard deviation = 1,
confirming correct scaling. The baseline produces neighbourhoods substantially more coherent than random assignment across 8 balanced genres.

Note, that when testing the recommender, 2x tracks by Monk Turner appeared. This would obviously skew the results with a sense of similarity. Will include a same-artist-excluded evaluation later.

# Qualitative baseline check

This will test the model manually, looking at a number of tracks recommended and listening manually to evaluate similarity 

I will carry out this test on each other proceeding Baseline models (PCA 146 and PCA 60), running the same seed tracks through these models to ask:
Did PCA change the actual recommendations, and do they still sound equally coherent?

One especially useful test is to flag recommendations as:

obvious similarity
interesting cross-genre similarity
doesn't make musical sense

Those “interesting cross-genre” cases are particularly valuable, because that's eventually where TasteBridge wants to operate.

We don't need a rigorous user study yet. 10 seeds × 3–5 recommendations is plenty for this baseline sanity check. Then keep those same seed tracks as a fixed qualitative benchmark throughout the modelling process.

In [19]:
small_tracks[
    [
        ("artist", "name"),
        ("track", "title"),
        ("track", "genre_top")
    ]
].sample(30, random_state=42)

artist  \
                                                name   
track_id                                               
54033                                  alright lover   
59876                                     Boy Friend   
42234                  Zlatne Uste Balkan Brass Band   
68893                                 Broke For Free   
97544                                      Amitron_7   
62191                                         Divans   
43883                                            Myo   
27610                            El Niño del Parking   
90826                                    The Mantles   
84605                                    EARTH-ENEMY   
39318     John Badger & The Moustache Riders of Doom   
67363                                  Directorsound   
68537                                    andybrannan   
96408                                 Mário Gajarský   
97542                                      Amitron_7   
98567                                         Hi-Rez   
149701                                           Sro   
110209                                 Circus Marcus   
63471                               Mutilation Rites   
55232                                  Mastermind XS   
87188                                  Eric & Magill   
122143              Anthony Donovan & Jaan Patterson   
123978                               BenJamin Banger   
143306                             Chase Alan Willis   
17608                                 Alash Ensemble   
71247                                         Dengaz   
149700                                           Sro   
71508                                            egr   
16339                                        Twizzle   
69747                               Manueljgrotesque   

                                                 track                 
                                                 title      genre_top  
track_id                                                               
54033                                        Snow Wave            Pop  
59876                                      Lovedropper           Rock  
42234                                      Lacin Cocek  International  
68893                                   Sidewalk Chalk     Electronic  
97544                      Escape Under Cover of Night     Electronic  
62191                                      Go digitale  International  
43883                                         crickets   Experimental  
27610                          Big Foot (Cuántos Años)  International  
90826                                     Reason's Run            Pop  
84605                                Me and My Friends            Pop  
39318             A Dream of Heaven in a Terminal Ward   Experimental  
67363                                 Before The March            Pop  
68537     Ambience Brooklyn Zoo Kids Waiting for Train   Experimental  
96408                                   Fucking Desire           Rock  
97542                                     Lotus Flower     Electronic  
98567                                   Fuck The World        Hip-Hop  
149701                                     Answering M     Electronic  
110209                             La tapa del viernes   Experimental  
63471                                          Goliath           Rock  
55232                                Stop That Mission  International  
87188                              Grandpa's Pink Wine            Pop  
122143                           Genome Chomsky (pt I)   Experimental  
123978                          Fuck Yall, Im Goin Pop        Hip-Hop  
143306                                 Take Your Pills   Instrumental  
17608                                        Bai-Taiga  International  
71247                                         Imortais        Hip-Hop  
149700                                    Rising Heart     Electronic  
71508                          Burn D

In [20]:
#
test_track_ids = [
    140,
    54033,
    59876,
    42234,
    68893,
    43883,
    123978,
    149701,
    63471,
    17608
]

In [21]:
[id_ for id_ in test_track_ids if id_ not in small_tracks.index]

[]

In [22]:
small_tracks.loc[
    test_track_ids,
    [
        ("artist", "name"),
        ("track", "title"),
        ("track", "genre_top")
    ]
]

artist                   track  \
                                     name                   title   
track_id                                                            
140       Alec K. Redfearn & the Eyesores      Queen Of The Wires   
54033                       alright lover               Snow Wave   
59876                          Boy Friend             Lovedropper   
42234       Zlatne Uste Balkan Brass Band             Lacin Cocek   
68893                      Broke For Free          Sidewalk Chalk   
43883                                 Myo                crickets   
123978                    BenJamin Banger  Fuck Yall, Im Goin Pop   
149701                                Sro             Answering M   
63471                    Mutilation Rites                 Goliath   
17608                      Alash Ensemble               Bai-Taiga   

                         
              genre_top  
track_id                 
140                Folk  
54033               Pop  
59876              Rock  
42234     International  
68893        Electronic  
43883      Experimental  
123978          Hip-Hop  
149701       Electronic  
63471              Rock  
17608     International

In [23]:
#Generate 5 recommendations for each seed

evaluation_rows = []

for seed_id in test_track_ids:

    seed = small_tracks.loc[seed_id]

    recommendations = recommend_similar_tracks(
        seed_id,
        n=5
    )

    for rec_id, rec in recommendations.iterrows():

        evaluation_rows.append({
            "seed_track_id": seed_id,
            "seed_artist": seed[("artist", "name")],
            "seed_title": seed[("track", "title")],
            "seed_genre": seed[("track", "genre_top")],

            "recommended_track_id": rec_id,
            "recommended_artist": rec["artist"],
            "recommended_title": rec["title"],
            "recommended_genre": rec["genre"],

            "cosine_similarity": rec["similarity"],

            "manual_similarity_1_5": np.nan,
            "connection_type": "",
            "notes": ""
        })

In [24]:
#Turn it into a table
manual_eval = pd.DataFrame(evaluation_rows)

manual_eval.head(50)

,seed_track_id,seed_artist,seed_title,seed_genre,recommended_track_id,recommended_artist,recommended_title,recommended_genre,cosine_similarity,manual_similarity_1_5,connection_type,notes
0,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,44805,Monk Turner + Fascinoma,Start Again,Pop,0.549527,NaN,,
1,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,6803,Watcha Clan,Balkan Qoulou,International,0.519641,NaN,,
2,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,77564,Bryyn,Abba Ingee,Pop,0.517595,NaN,,
3,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,110451,Papascandy,Linton,International,0.506011,NaN,,
4,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,52953,Marissa Nadler,Your Heart Is A Twisted Vine,Folk,0.492149,NaN,,
5,54033,alright lover,Snow Wave,Pop,145556,This Mess is Mine,Roommates (Piano Version by AGPB),Folk,0.500335,NaN,,
6,54033,alright lover,Snow Wave,Pop,63456,Big Blood,Away pt. II,Folk,0.453994,NaN,,
7,54033,alright lover,Snow Wave,Pop,14571,Ergo Phizmiz,Through the Doors of the Circus,Instrumental,0.441940,NaN,,
8,54033,alright lover,Snow Wave,Pop,114070,Blue Dot Sessions,Grand Fell,Instrumental,0.430511,NaN,,
9,54033,alright lover,Snow Wave,Pop,134388,Scott Holmes,Magical Moments,Pop,0.427252,NaN,,


In [25]:
#verifying the shape of the manual evaluation table
manual_eval.shape

(50, 12)

In [26]:
#verifying the data types in the manual evaluation table
manual_eval.dtypes

seed_track_id              int64
seed_artist                  str
seed_title                   str
seed_genre                   str
recommended_track_id       int64
recommended_artist           str
recommended_title            str
recommended_genre            str
cosine_similarity        float64
manual_similarity_1_5    float64
connection_type              str
notes                        str
dtype: object

In [31]:
#save the recommendations for carrying out assessment
manual_eval.to_csv(
    "../data/processed/baseline1_manual_evaluation.csv",
    index=False
)

# Listen to tracks directly in this notebook

Scores get added to the relevant .csv for a machine vs human comparison

similarity_score:

1 = sounds unrelated

2 = weak connection

3 = some clear similarity

4 = strongly related

5 = very similar


connection_type:

rhythm

timbre

mood

instrumentation

energy

production (maybe less relevant)

harmony

vocals

cross-genre

unclear

### Guidance for Rating

Similarity rating

Use a 1–5 scale.

Score	Meaning
1	No meaningful musical similarity. The recommendation feels unrelated.
2	Weak similarity. One or two minor characteristics may connect them, but overall they sound quite different.
3	Moderate similarity. There is a recognisable musical connection, although there are also substantial differences.
4	Strong similarity. Several important musical characteristics clearly connect the tracks.
5	Very strong similarity. The tracks are highly alike in sound, structure, atmosphere or production.

Example ratings

A 4 might be:

Similar percussion, tempo and atmosphere, despite different genres.

A 3 might be:

Similar vocal style and mood, but instrumentation and rhythm are quite different.

A 2 might be:

Both are acoustic, but otherwise the connection is weak.

A 1 might be:

Different tempo, instrumentation, mood and production; no obvious connection.

Listening procedure

For consistency, listen to roughly the same amount of each track. Around 20–30 seconds is enough initially, but listen longer when the relationship is unclear.

Listen to the seed first, then the recommendation.

Try not to look at the cosine similarity before deciding your score if possible. We do not want the model's score to influence the human judgement.

In [27]:
from IPython.display import Audio, display
from pathlib import Path

In [28]:
def get_fma_audio_path(track_id):
    track_id_str = f"{track_id:06d}"
    
    return (
        Path("../data/raw/fma_small")
        / track_id_str[:3]
        / f"{track_id_str}.mp3"
    )

In [29]:
get_fma_audio_path(140)

PosixPath('../data/raw/fma_small/000/000140.mp3')

In [30]:
def listen_to_pair(seed_id, rec_id):
    print("SEED")
    print(
        small_tracks.loc[
            seed_id,
            [("artist", "name"), ("track", "title")]
        ]
    )
    display(Audio(get_fma_audio_path(seed_id)))

    print("\nRECOMMENDATION")
    print(
        small_tracks.loc[
            rec_id,
            [("artist", "name"), ("track", "title")]
        ]
    )
    display(Audio(get_fma_audio_path(rec_id)))

In [36]:
import librosa

for track_id in test_track_ids:
    path = get_fma_audio_path(track_id)

    try:
        y, sr = librosa.load(path, duration=2)
        print(track_id, "OK")
    except Exception as e:
        print(track_id, "BROKEN:", e)

140 OK
54033 OK
59876 OK
42234 OK
68893 OK
43883 OK
123978 OK
149701 OK
63471 OK
17608 OK


In [37]:
listen_to_pair(63471, 145199)
# similarity_score = 2
# connection_type = unclear;
# could be in same playlist but different rock styles. connected on electric guitar.

SEED
artist  name     Mutilation Rites
track   title             Goliath
Name: 63471, dtype: str



RECOMMENDATION
artist  name                     Conduit
track   title    Opening the Mouth/ Salt
Name: 145199, dtype: str


In [38]:
listen_to_pair(63471, 86417)
# similarity_score = 4
# connection_type = instrumentation; energy; mood; timbre
# nice connection

SEED
artist  name     Mutilation Rites
track   title             Goliath
Name: 63471, dtype: str



RECOMMENDATION
artist  name                        One Master
track   title    The Destroyer (Parts 1 and 2)
Name: 86417, dtype: str


In [39]:
listen_to_pair(63471, 54942)
# similarity_score = 3
# connection_type = mood;



SEED
artist  name     Mutilation Rites
track   title             Goliath
Name: 63471, dtype: str



RECOMMENDATION
artist  name               Dolorvotre
track   title    Brilliant Brightness
Name: 54942, dtype: str


In [40]:
listen_to_pair(63471, 73521)
# similarity_score = 3
# connection_type = unclear; cross-genre;
# connection_type = where'd he go?!

SEED
artist  name     Mutilation Rites
track   title             Goliath
Name: 63471, dtype: str



RECOMMENDATION
artist  name           Hounds Of Hate
track   title    Brotherhood Of Night
Name: 73521, dtype: str


In [41]:
listen_to_pair(63471, 3833)
# similarity_score = 3
# connection_type = mood; energy;


SEED
artist  name     Mutilation Rites
track   title             Goliath
Name: 63471, dtype: str



RECOMMENDATION
artist  name     Lightning Bolt
track   title          Track 01
Name: 3833, dtype: str


In [42]:
listen_to_pair(17608, 43028)
# similarity_score = 4
# connection_type = instrumentation; mood; energy; timbre; harmony; rhythm; vocals;


SEED
artist  name     Alash Ensemble
track   title         Bai-Taiga
Name: 17608, dtype: str



RECOMMENDATION
artist  name     Huun Huur Tu
track   title      Samagaldai
Name: 43028, dtype: str


In [43]:
listen_to_pair(17608, 116706)
# similarity_score = 2
# connection_type = timbre; instrumentation; 
# weak connection but would put in a similar playlist

SEED
artist  name     Alash Ensemble
track   title         Bai-Taiga
Name: 17608, dtype: str



RECOMMENDATION
artist  name     Howie Mitchell
track   title      Henry Martin
Name: 116706, dtype: str


In [44]:
listen_to_pair(17608, 68840)
# similarity_score = 2
# connection_type = unclear;
# weak connection. maybe would put in a similar playlist

SEED
artist  name     Alash Ensemble
track   title         Bai-Taiga
Name: 17608, dtype: str



RECOMMENDATION
artist  name            Howie Mitchell
track   title    John's Laughing Place
Name: 68840, dtype: str


In [45]:
listen_to_pair(17608, 39663)
# similarity_score = 3
# connection_type = instrumentation; mood; timbre; energy;
# medium connection. would put in a similar playlist

SEED
artist  name     Alash Ensemble
track   title         Bai-Taiga
Name: 17608, dtype: str



RECOMMENDATION
artist  name            Quiet Hooves
track   title    Til It Stops Talkin
Name: 39663, dtype: str


In [46]:
listen_to_pair(17608, 68841)
# similarity_score = 3
# connection_type = timbre; mood; energy;
# would playlist together

SEED
artist  name     Alash Ensemble
track   title         Bai-Taiga
Name: 17608, dtype: str



RECOMMENDATION
artist  name     Howie Mitchell
track   title    Old Molly Hare
Name: 68841, dtype: str


## Leave the audio section above!

# Import the .csv back into the notebook

In [31]:
manual_eval = pd.read_csv(
    "../data/processed/baseline1_manual_evaluation.csv",
    sep=";"
)

In [32]:
manual_eval.shape

(50, 12)

In [33]:
manual_eval.head()

,seed_track_id,seed_artist,seed_title,seed_genre,recommended_track_id,recommended_artist,recommended_title,recommended_genre,cosine_similarity,manual_similarity_1_5,connection_type,connection_type.1
0,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,44805,Monk Turner + Fascinoma,Start Again,Pop,0.549527,3,mood; energy; production; harmony,NaN
1,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,6803,Watcha Clan,Balkan Qoulou,International,0.519641,2,unclear; cross-genre,weaker connection but would put in a similar p...
2,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,77564,Bryyn,Abba Ingee,Pop,0.517595,4,mood; energy; harmony; vocals,NaN
3,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,110451,Papascandy,Linton,International,0.506011,2,mood; unclear; cross-genre,weaker connection but would put in a similar p...
4,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,52953,Marissa Nadler,Your Heart Is A Twisted Vine,Folk,0.492149,4,energy; mood; vocals; production,NaN


In [34]:
path = "../data/processed/baseline1_manual_evaluation.csv"

with open(path, "r", encoding="utf-8-sig") as f:
    for _ in range(3):
        print(repr(f.readline()))

'seed_track_id;seed_artist;seed_title;seed_genre;recommended_track_id;recommended_artist;recommended_title;recommended_genre;cosine_similarity;manual_similarity_1_5;connection_type;connection_type\n'
'140;Alec K. Redfearn & the Eyesores;Queen Of The Wires;Folk;44805;Monk Turner + Fascinoma;Start Again;Pop;0.5495273225835039;3;"mood; energy; production; harmony";\n'
'140;Alec K. Redfearn & the Eyesores;Queen Of The Wires;Folk;6803;Watcha Clan;Balkan Qoulou;International;0.5196407307692211;2;"unclear; cross-genre";weaker connection but would put in a similar playlist\n'


In [35]:
manual_eval["manual_similarity_1_5"].isna().sum()

np.int64(0)

# Calculate the Baseline 1 summary metrics after completed ratings

In [36]:
manual_eval["manual_similarity_1_5"].describe()

count    50.000000
mean      2.740000
std       0.899206
min       1.000000
25%       2.000000
50%       3.000000
75%       3.000000
max       5.000000
Name: manual_similarity_1_5, dtype: float64

In [37]:
mean_manual_similarity = manual_eval["manual_similarity_1_5"].mean()

pct_3_or_more = (
    manual_eval["manual_similarity_1_5"] >= 3
).mean()

pct_4_or_more = (
    manual_eval["manual_similarity_1_5"] >= 4
).mean()

print("Mean manual similarity:", mean_manual_similarity)
print("% rated 3 or more:", pct_3_or_more)
print("% rated 4 or more:", pct_4_or_more)

Mean manual similarity: 2.74
% rated 3 or more: 0.66
% rated 4 or more: 0.16


In [38]:
manual_eval[
    ["cosine_similarity", "manual_similarity_1_5"]
].corr()



,cosine_similarity,manual_similarity_1_5
cosine_similarity,1.000000,0.085009
manual_similarity_1_5,0.085009,1.000000


In [39]:
manual_eval["same_genre"] = (
    manual_eval["seed_genre"]
    == manual_eval["recommended_genre"]
)

manual_eval.groupby("same_genre")[
    "manual_similarity_1_5"
].mean()

same_genre
False    2.466667
True     3.150000
Name: manual_similarity_1_5, dtype: float64

In [40]:
small_features.dtypes.value_counts()

float64    518
Name: count, dtype: int64

In [41]:
connection_counts = (
    manual_eval["connection_type"]
    .dropna()
    .str.split(";")
    .explode()
    .str.strip()
    .str.lower()
    .value_counts()
)

connection_counts

connection_type
mood               33
energy             24
timbre             15
unclear            14
instrumentation    13
harmony            11
cross-genre        11
vocals              8
production          5
rhythm              1
Name: count, dtype: int64

In [42]:
manual_eval[
    ["cosine_similarity", "manual_similarity_1_5"]
].corr(method="spearman")

,cosine_similarity,manual_similarity_1_5
cosine_similarity,1.000000,0.105821
manual_similarity_1_5,0.105821,1.000000


In [43]:
manual_eval = manual_eval.rename(
    columns={"connection_type.1": "notes"}
)

In [44]:
def cosine_feature_contributions(seed_id, rec_id):
    seed_pos = small_tracks.index.get_loc(seed_id)
    rec_pos = small_tracks.index.get_loc(rec_id)

    x = X_scaled[seed_pos]
    y = X_scaled[rec_pos]

    contributions = (x * y) / (
        np.linalg.norm(x) * np.linalg.norm(y)
    )

    result = pd.DataFrame({
        "feature": small_features.columns,
        "contribution": contributions
    })

    return result.sort_values(
        "contribution",
        ascending=False
    )

In [45]:
cosine_feature_contributions(140, 44805).head(20)

,feature,contribution
459,"(spectral_contrast, std, 05)",0.019073
483,"(tonnetz, mean, 03)",0.013591
74,"(chroma_cens, std, 03)",0.013433
424,"(spectral_contrast, max, 05)",0.012262
489,"(tonnetz, median, 03)",0.012206
47,"(chroma_cens, median, 12)",0.010944
497,"(tonnetz, min, 05)",0.010107
80,"(chroma_cens, std, 09)",0.009904
119,"(chroma_cqt, mean, 12)",0.009116
378,"(mfcc, std, 07)",0.009000


In [46]:
contributions = cosine_feature_contributions(140, 44805)

In [47]:
contributions["family"] = contributions["feature"].apply(
    lambda x: x[0]
)

In [48]:
contributions.head()

,feature,contribution,family
459,"(spectral_contrast, std, 05)",0.019073,spectral_contrast
483,"(tonnetz, mean, 03)",0.013591,tonnetz
74,"(chroma_cens, std, 03)",0.013433,chroma_cens
424,"(spectral_contrast, max, 05)",0.012262,spectral_contrast
489,"(tonnetz, median, 03)",0.012206,tonnetz


In [49]:
family_contributions = (
    contributions
    .groupby("family")["contribution"]
    .sum()
    .sort_values(ascending=False)
)

family_contributions

family
chroma_cens           0.159279
mfcc                  0.113373
tonnetz               0.104499
chroma_cqt            0.090202
spectral_contrast     0.045756
chroma_stft           0.029603
rmse                  0.005201
spectral_bandwidth    0.001912
zcr                   0.001759
spectral_centroid    -0.000738
spectral_rolloff     -0.001319
Name: contribution, dtype: float64

In [50]:
family_contributions.sum()

np.float64(0.5495273225835043)

In [51]:
contributions["abs_contribution"] = (
    contributions["contribution"].abs()
)

In [52]:
family_summary = (
    contributions
    .groupby("family")
    .agg(
        signed_contribution=("contribution", "sum"),
        absolute_contribution=("abs_contribution", "sum"),
        n_features=("feature", "count")
    )
)

In [53]:
family_summary["share_of_absolute_contribution"] = (
    family_summary["absolute_contribution"]
    / family_summary["absolute_contribution"].sum()
)

In [54]:
family_summary = family_summary.sort_values(
    "absolute_contribution",
    ascending=False
)

family_summary

,signed_contribution,absolute_contribution,n_features,share_of_absolute_contribution
family,,,,
mfcc,0.113373,0.200540,140,0.259304
chroma_cens,0.159279,0.186587,84,0.241262
tonnetz,0.104499,0.124329,42,0.160761
chroma_cqt,0.090202,0.119718,84,0.154799
spectral_contrast,0.045756,0.070569,49,0.091248
chroma_stft,0.029603,0.053578,84,0.069278
rmse,0.005201,0.005263,7,0.006805
spectral_rolloff,-0.001319,0.004131,7,0.005342
spectral_centroid,-0.000738,0.003414,7,0.004414


In [55]:
family_summary["share_pct"] = (
    family_summary["share_of_absolute_contribution"] * 100
)

family_summary[
    [
        "n_features",
        "signed_contribution",
        "absolute_contribution",
        "share_pct"
    ]
]

,n_features,signed_contribution,absolute_contribution,share_pct
family,,,,
mfcc,140,0.113373,0.200540,25.930357
chroma_cens,84,0.159279,0.186587,24.126171
tonnetz,42,0.104499,0.124329,16.076129
chroma_cqt,84,0.090202,0.119718,15.479865
spectral_contrast,49,0.045756,0.070569,9.124771
chroma_stft,84,0.029603,0.053578,6.927796
rmse,7,0.005201,0.005263,0.680547
spectral_rolloff,7,-0.001319,0.004131,0.534172
spectral_centroid,7,-0.000738,0.003414,0.441408


In [56]:
family_summary["mean_abs_contribution_per_feature"] = (
    family_summary["absolute_contribution"]
    / family_summary["n_features"]
)

family_summary.sort_values(
    "mean_abs_contribution_per_feature",
    ascending=False
)

,signed_contribution,absolute_contribution,n_features,share_of_absolute_contribution,share_pct,mean_abs_contribution_per_feature
family,,,,,,
tonnetz,0.104499,0.124329,42,0.160761,16.076129,0.002960
chroma_cens,0.159279,0.186587,84,0.241262,24.126171,0.002221
spectral_contrast,0.045756,0.070569,49,0.091248,9.124771,0.001440
mfcc,0.113373,0.200540,140,0.259304,25.930357,0.001432
chroma_cqt,0.090202,0.119718,84,0.154799,15.479865,0.001425
rmse,0.005201,0.005263,7,0.006805,0.680547,0.000752
chroma_stft,0.029603,0.053578,84,0.069278,6.927796,0.000638
spectral_rolloff,-0.001319,0.004131,7,0.005342,0.534172,0.000590
spectral_centroid,-0.000738,0.003414,7,0.004414,0.441408,0.000488


In [57]:
family_summary["signed_contribution"].sum()

np.float64(0.5495273225835043)

Tonnetz has the strongest contribution per individual feature, while MFCC and chroma families account for the largest overall share of the similarity because they contain many more dimensions.

## Baseline findings

The first baseline used all 518 standardized FMA audio features with cosine
nearest-neighbour retrieval. Recommendations from the same artist were excluded.

### Quantitative evaluation
- Genre agreement@10: **0.3434**
- Query time: **0.0282 seconds for 100 queries**

### Manual evaluation
A qualitative evaluation was conducted on 50 recommendation pairs generated
from 10 fixed seed tracks.

- Mean human similarity: **2.74 / 5**
- **66%** of recommendations scored 3 or higher
- **16%** scored 4 or higher
- Same-genre mean rating: **3.15**
- Cross-genre mean rating: **2.47**
- Pearson correlation between cosine similarity and human rating: **0.085**

The baseline produces meaningful recommendations in a majority of cases, but
strong matches are relatively uncommon. Same-genre recommendations perform
better than cross-genre recommendations, while cosine similarity itself shows
little relationship with perceived similarity among the retrieved tracks.

This model provides the reference point for evaluating PCA-based representations.